# Learned Stage-Wise Curvature Tuning on PathMNIST

This notebook evaluates Learned Stage-Wise Curvature Tuning (SW-CT) on the PathMNIST dataset using an ImageNet-pretrained ResNet-50.

PathMNIST is a medical image-classification dataset containing histopathology images. Its visual characteristics differ substantially from the natural images used for ImageNet pretraining, providing a useful domain-shift experiment for evaluating Learned SW-CT.

The experiments compare four conditions:

1. **Baseline** — the original pretrained ResNet with ReLU activations and a trained downstream classifier.
2. **Single-Parameter Curvature Tuning (S-CT)** — one global beta selected through validation-based exhaustive search.
3. **Learned SW-CT with fixed initialization** — four trainable stage-wise beta parameters initialized at 0.78.
4. **Learned SW-CT with random initialization** — four trainable stage-wise beta parameters independently initialized between 0.70 and 0.99.

Each condition is evaluated using seeds 42, 43, and 44.

Experiments are conducted for both 20 and 30 epochs to determine whether additional optimization improves performance or changes the learned stage-wise beta values.

Wall-clock execution time is recorded to compare the computational cost of Baseline, S-CT, and Learned SW-CT.

In [2]:
!nvidia-smi

Fri Oct  9 20:47:13 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 610.43.02              KMD Version: 610.43.02     CUDA UMD Version: 13.3     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  NVIDIA RTX A6000               Off |   00000000:0C:00.0 Off |                  Off |
| 30%   22C    P8             21W /  300W |       1MiB /  49140MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+-----

In [2]:
%cd /content

!git clone -b main \
    https://github.com/NiftySnek173/research-curvature-tuning.git

%cd /content/research-curvature-tuning/src/curvature-tuning

!git branch --show-current
!git log -1 --oneline

/content
fatal: destination path 'curvature-tuning-research' already exists and is not an empty directory.
/content/curvature-tuning-research/src/curvature-tuning
stage-wise-ct
27ee9f0 (HEAD -> stage-wise-ct, origin/stage-wise-ct, origin/HEAD) updated food 101 execution


## Environment Setup

The repository dependencies are installed before running the experiments.

After installation, the Colab runtime should be restarted so that the required package versions are loaded correctly.

In [2]:
%pip install -q -r requirements.txt
%pip install --force-reinstall --no-cache-dir "numpy==1.26.3"

%pip install --no-cache-dir --force-reinstall --no-deps "pyarrow==16.1.0"


Note: you may need to restart the kernel to use updated packages.
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 18.3/18.3 MB 129.5 MB/s  0:00:00
  Attempting uninstall: numpy
    Found existing installation: numpy 1.26.3
    Uninstalling numpy-1.26.3:
      Successfully uninstalled numpy-1.26.3
Note: you may need to restart the kernel to use updated packages.
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 40.8/40.8 MB 154.8 MB/s  0:00:00 eta 0:00:01
  Attempting uninstall: pyarrow
    Found existing installation: pyarrow 25.0.1
    Uninstalling pyarrow-25.0.1:
      Successfully uninstalled pyarrow-25.0.1
Note: you may need to restart the kernel to use updated packages.


In [1]:
%cd /content/research-curvature-tuning/src/curvature-tuning

import os
import torch

os.environ["WANDB_MODE"] = "disabled"

print("Working directory:", os.getcwd())
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

/content/curvature-tuning-research/src/curvature-tuning
Working directory: /content/curvature-tuning-research/src/curvature-tuning
PyTorch: 2.6.0+cu124
CUDA available: True
GPU: NVIDIA L4


## Arabic Digits Dataset

Before running the experiments, the Arabic Digits data loaders are checked to confirm that the downstream dataset can be loaded correctly.

The same dataset split and random seed protocol are used for Baseline, S-CT, and Learned SW-CT so that the methods are compared under the same conditions.

In [2]:
import aiohttp
from datasets import load_dataset, DownloadConfig

download_config = DownloadConfig(
    max_retries=5,
    storage_options={
        "client_kwargs": {
            "timeout": aiohttp.ClientTimeout(
                total=7200,       # Allow up to 2 hours overall
                connect=120,
                sock_read=600,    # Allow pauses of up to 10 minutes
            )
        }
    },
)

pathmnist_cached = load_dataset(
    "randall-lab/medmnist",
    name="pathmnist",
    trust_remote_code=True,
    download_config=download_config,
)

print("PathMNIST download and preparation complete.")
print(pathmnist_cached)

/content/.venv/lib/python3.11/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm
Generating train split: 89996 examples [00:23, 3763.21 examples/s]
Generating test split: 7180 examples [00:01, 3678.95 examples/s]
Generating validation split: 10004 examples [00:02, 3781.66 examples/s]

PathMNIST download and preparation complete.
DatasetDict({
    train: Dataset({
        features: ['image', 'label'],
        num_rows: 89996
    })
    test: Dataset({
        features: ['image', 'label'],
        num_rows: 7180
    })
    validation: Dataset({
        features: ['image', 'label'],
        num_rows: 10004
    })
})


In [3]:
from utils.data import get_data_loaders

train_loader, test_loader, val_loader = get_data_loaders(
    "imagenet_to_medmnist/pathmnist",
    train_batch_size=32,
    test_batch_size=128,
    seed=42,
)

print("Train samples:", len(train_loader.dataset))
print("Validation samples:", len(val_loader.dataset))
print("Test samples:", len(test_loader.dataset))

images, labels = next(iter(train_loader))

print("Image batch shape:", images.shape)
print("Label batch shape:", labels.shape)
print("Labels:", labels[:10])

Train samples: 89996
Validation samples: 10004
Test samples: 7180
Image batch shape: torch.Size([32, 3, 224, 224])
Label batch shape: torch.Size([32])
Labels: tensor([2, 1, 3, 7, 5, 0, 0, 3, 5, 0])


# ResNet-50 Experiments

ResNet-50 is evaluated first because it was used during the initial development of Learned SW-CT.

The experiment compares Baseline, S-CT, fixed-initialization SW-CT, and random-initialization SW-CT.

All methods use the same ImageNet-pretrained backbone, Arabic Digits dataset split, experimental seeds, and downstream training protocol.

## ResNet-50 — 20-Epoch Evaluation

The first evaluation uses 20 training epochs.

This provides the primary reference experiment and maintains compatibility with the earlier Learned SW-CT work.

### Methods

**Baseline**

The pretrained ResNet-50 retains its original ReLU activations. The backbone is frozen and only the downstream classifier is trained.

**S-CT**

The original Single-Parameter Curvature Tuning method searches over a single beta shared throughout the network. Candidate beta values from 0.70 to 1.00 are evaluated using validation performance, and the best candidate is evaluated on the test set.

The recorded S-CT execution time includes the complete beta search rather than only the final selected beta.

**Learned SW-CT — Fixed Initialization**

Four trainable beta parameters are assigned to the four ResNet stages. All four begin at beta = 0.78.

This preserves the initialization used in the original Learned SW-CT experiments.

**Learned SW-CT — Random Initialization**

Four trainable stage-wise beta parameters are initialized independently between 0.70 and 0.99.

The random initialization is generated deterministically from the experiment seed. This allows the experiment to test whether Learned SW-CT depends on the fixed 0.78 starting value while remaining reproducible.

In [3]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-03 23:38:21.125 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet50_seed42_epochs20.log
2026-10-03 23:38:21.128 | INFO     | __main__:main:78 - Running on cuda
2026-10-03 23:38:23.857 | INFO     | __main__:main:105 - Testing baseline...
2026-10-03 23:38:23.912 | INFO     | __main__:main:116 - Number of trainable parameters: 18441
2026-10-03 23:38:23.912 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-03 23:43:46.042 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.268570, Accuracy: 6.25%
2026-10-03 23:43:46.486 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.195587, Accuracy: 20.27%
2026-10-03 23:43:46.951 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.018680, Accuracy: 35.31%
2026-10-03 23:43:47.416 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.821339, Accuracy: 46.15%
2026-10-03 23:43:47.859 | INFO     | train:train_epoch:47 - Epoch 1, Step

In [3]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-05 17:37:34.529 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet50_seed43_epochs20.log
2026-10-05 17:37:34.537 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /content/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|██████████████████████████████████████| 97.8M/97.8M [00:01<00:00, 85.5MB/s]
2026-10-05 17:37:39.092 | INFO     | __main__:main:105 - Testing baseline...
2026-10-05 17:37:39.134 | INFO     | __main__:main:116 - Number of trainable parameters: 18441
2026-10-05 17:37:39.134 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-05 17:42:25.386 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.252942, Accuracy: 9.38%
2026-10-05 17:42:25.694 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.169016, Accuracy: 12.87%
2026-10-05 17:42:25.967 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, L

In [4]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-06 00:07:40.648 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet50_seed44_epochs20.log
2026-10-06 00:07:40.653 | INFO     | __main__:main:78 - Running on cuda
2026-10-06 00:07:43.949 | INFO     | __main__:main:105 - Testing baseline...
2026-10-06 00:07:44.086 | INFO     | __main__:main:116 - Number of trainable parameters: 18441
2026-10-06 00:07:44.087 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-06 00:12:32.269 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.194133, Accuracy: 12.50%
2026-10-06 00:12:32.583 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.115887, Accuracy: 21.81%
2026-10-06 00:12:32.880 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.955972, Accuracy: 33.71%
2026-10-06 00:12:33.174 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.760243, Accuracy: 45.64%
2026-10-06 00:12:33.474 | INFO     | train:train_epoch:47 - Epoch 1, Ste

### Learned SW-CT with Fixed Beta Initialization

The original Learned SW-CT configuration is first reproduced using the fixed initialization:

\[[\beta_1,\beta_2,\beta_3,\beta_4]=[0.78,0.78,0.78,0.78].\]

The initial value is only a starting point. During training, the four beta parameters are optimized independently together with the downstream classifier.

These runs provide the reference against which random initialization will be compared.

In [5]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-06 07:16:57.806 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed42_epochs20_initfixed0.78_betalr0.01.log
2026-10-06 07:16:57.879 | INFO     | __main__:main:302 - Running on cuda
2026-10-06 07:17:01.802 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-06 07:17:01.802 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-06 07:17:01.912 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-06 07:17:01.913 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-06 07:17:01.913 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-06 07:17:03.744 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.201935, Accuracy: 9.38%
2026-10-06 07:17:56.030 | INFO     | train:tr

In [3]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-07 02:55:28.621 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed43_epochs20_initfixed0.78_betalr0.01.log
2026-10-07 02:55:28.691 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /home/ubuntu/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 125MB/s]
2026-10-07 02:55:32.352 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-07 02:55:32.353 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-07 02:55:32.477 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-07 02:55:32.478 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-07 02:55:32.478 

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-07 06:28:19.954 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed44_epochs20_initfixed0.78_betalr0.01.log
2026-10-07 06:28:20.033 | INFO     | __main__:main:302 - Running on cuda
2026-10-07 06:28:23.937 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-07 06:28:23.937 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-07 06:28:24.046 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-07 06:28:24.047 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-07 06:28:24.047 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-07 06:28:26.763 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.091443, Accuracy: 15.62%
2026-10-07 06:28:48.156 | INFO     | train:t

### Learned SW-CT with Random Beta Initialization

The fixed beta = 0.78 initialization may raise the question of whether Learned SW-CT performs well only because its starting point was informed by the earlier S-CT experiments.

To test this dependency, each of the four stage-wise beta parameters is now initialized independently from a uniform distribution between 0.70 and 0.99.

The initialization is reproducible: the random generator is seeded using the experiment seed. Therefore, each seed always receives the same initial beta vector.

If random initialization produces similar performance to the fixed 0.78 experiment, this provides evidence that the Learned SW-CT result is not dependent on a single hand-selected initialization.

In [5]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-07 10:03:37.863 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed42_epochs20_initrandom_betalr0.01.log
2026-10-07 10:03:37.941 | INFO     | __main__:main:302 - Running on cuda
2026-10-07 10:03:42.171 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-07 10:03:42.172 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-07 10:03:42.281 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-07 10:03:42.282 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-07 10:03:42.282 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-07 10:03:45.055 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.215927, Accuracy: 12.50%
2026-10-07 10:04:06.970 | INFO  

In [6]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-07 13:35:24.260 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed43_epochs20_initrandom_betalr0.01.log
2026-10-07 13:35:24.335 | INFO     | __main__:main:302 - Running on cuda
2026-10-07 13:35:28.518 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-07 13:35:28.518 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-07 13:35:28.650 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-07 13:35:28.650 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-07 13:35:28.651 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-07 13:35:31.562 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.309585, Accuracy: 3.12%
2026-10-07 13:35:52.831 | INFO 

In [7]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-07 17:08:28.224 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed44_epochs20_initrandom_betalr0.01.log
2026-10-07 17:08:28.299 | INFO     | __main__:main:302 - Running on cuda
2026-10-07 17:08:32.557 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-07 17:08:32.558 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-07 17:08:32.686 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-07 17:08:32.688 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-07 17:08:32.688 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-07 17:08:35.726 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.136764, Accuracy: 12.50%
2026-10-07 17:08:57.347 | INFO

# ResNet-50 — 30-Epoch Evaluation

The same experiments are now repeated for 30 epochs.

The purpose of increasing the training budget is to determine whether the 20-epoch results are limited by insufficient optimization.

If a method improves substantially with 30 epochs, this suggests that additional optimization is useful. If performance remains similar, it indicates that the method has largely stabilized within the original 20-epoch training budget.

All other experimental settings remain unchanged.

For random-initialization SW-CT, the same seed produces exactly the same initial four-beta vector in both the 20-epoch and 30-epoch experiments. Therefore, initialization is held constant while the training duration changes.

Execution time is again recorded to measure the computational cost of extending training from 20 to 30 epochs.

In [4]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-09 21:20:45.525 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet50_seed42_epochs30.log
2026-10-09 21:20:45.529 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /home/ubuntu/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 126MB/s]
2026-10-09 21:20:52.329 | INFO     | __main__:main:105 - Testing baseline...
2026-10-09 21:20:52.401 | INFO     | __main__:main:116 - Number of trainable parameters: 18441
2026-10-09 21:20:52.401 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-09 21:23:49.149 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.268645, Accuracy: 6.25%
2026-10-09 21:23:49.770 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.195633, Accuracy: 20.33%
2026-10-09 21:23:50.249 | INFO     | train:train_epoch:47 - Epoch 1, Step 20

IOPub message rate exceeded.
The Jupyter server will temporarily stop sending output
to the client in order to avoid crashing it.
To change this limit, set the config variable
`--ServerApp.iopub_msg_rate_limit`.

Current values:
ServerApp.iopub_msg_rate_limit=1000.0 (msgs/sec)
ServerApp.rate_limit_window=3.0 (secs)



2026-10-09 23:36:44.286 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.203557, Accuracy: 3.12%
2026-10-09 23:36:44.740 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.200909, Accuracy: 11.76%
2026-10-09 23:36:45.294 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 2.194445, Accuracy: 12.67%
2026-10-09 23:36:45.821 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 2.190061, Accuracy: 13.27%
2026-10-09 23:36:46.303 | INFO     | train:train_epoch:47 - Epoch 1, Step 400, Loss: 2.187085, Accuracy: 13.74%
2026-10-09 23:36:46.805 | INFO     | train:train_epoch:47 - Epoch 1, Step 500, Loss: 2.185732, Accuracy: 13.95%
2026-10-09 23:36:47.244 | INFO     | train:train_epoch:47 - Epoch 1, Step 600, Loss: 2.183466, Accuracy: 14.21%
2026-10-09 23:36:47.693 | INFO     | train:train_epoch:47 - Epoch 1, Step 700, Loss: 2.181360, Accuracy: 14.33%
2026-10-09 23:36:48.165 | INFO     | train:train_epoch:47 - Epoch 1, Step 800, Loss: 2.177791, Accuracy: 14

In [3]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-10 12:46:24.551 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet50_seed43_epochs30.log
2026-10-10 12:46:24.554 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /home/ubuntu/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|██████████████████████████████████████| 97.8M/97.8M [00:01<00:00, 90.5MB/s]
2026-10-10 12:46:29.356 | INFO     | __main__:main:105 - Testing baseline...
2026-10-10 12:46:29.434 | INFO     | __main__:main:116 - Number of trainable parameters: 18441
2026-10-10 12:46:29.435 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-10 12:51:05.788 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.252966, Accuracy: 9.38%
2026-10-10 12:51:06.477 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.169025, Accuracy: 12.75%
2026-10-10 12:51:07.077 | INFO     | train:train_epoch:47 - Epoch 1, Step 20

In [4]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-10 21:08:28.357 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_medmnist-pathmnist_resnet50_seed44_epochs30.log
2026-10-10 21:08:28.363 | INFO     | __main__:main:78 - Running on cuda
2026-10-10 21:08:33.822 | INFO     | __main__:main:105 - Testing baseline...
2026-10-10 21:08:33.899 | INFO     | __main__:main:116 - Number of trainable parameters: 18441
2026-10-10 21:08:33.899 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-10 21:12:57.022 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.194161, Accuracy: 12.50%
2026-10-10 21:12:57.787 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.115885, Accuracy: 21.84%
2026-10-10 21:12:58.455 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.955981, Accuracy: 33.74%
2026-10-10 21:12:59.279 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.760258, Accuracy: 45.65%
2026-10-10 21:13:00.000 | INFO     | train:train_epoch:47 - Epoch 1, Ste

In [5]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-11 05:31:47.735 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed42_epochs30_initfixed0.78_betalr0.01.log
2026-10-11 05:31:47.834 | INFO     | __main__:main:302 - Running on cuda
2026-10-11 05:31:52.310 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-11 05:31:52.311 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 05:31:52.473 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-11 05:31:52.474 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 05:31:52.475 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-11 05:31:56.059 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.201942, Accuracy: 9.38%
2026-10-11 05:32:20.279 | INFO     | train:tr

In [6]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-11 11:32:35.545 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed43_epochs30_initfixed0.78_betalr0.01.log
2026-10-11 11:32:35.646 | INFO     | __main__:main:302 - Running on cuda
2026-10-11 11:32:39.390 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-11 11:32:39.391 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-11 11:32:39.583 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-11 11:32:39.584 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-11 11:32:39.585 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-11 11:32:43.613 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.304987, Accuracy: 6.25%
2026-10-11 11:33:08.219 | INFO     | train:tr

In [6]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-19 15:25:08.117 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed44_epochs30_initfixed0.78_betalr0.01.log
2026-10-19 15:25:08.176 | INFO     | __main__:main:302 - Running on cuda
2026-10-19 15:25:10.407 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-19 15:25:10.407 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-19 15:25:10.488 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-19 15:25:10.489 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-19 15:25:10.489 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-19 15:25:12.205 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.091487, Accuracy: 15.62%
2026-10-19 15:25:50.592 | INFO     | train:t

In [8]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-12 01:32:59.546 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed42_epochs30_initrandom_betalr0.01.log
2026-10-12 01:32:59.650 | INFO     | __main__:main:302 - Running on cuda
2026-10-12 01:33:03.605 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-12 01:33:03.606 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-12 01:33:03.752 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-12 01:33:03.754 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-12 01:33:03.755 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-12 01:33:06.625 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.215927, Accuracy: 12.50%
2026-10-12 01:33:30.399 | INFO  

In [9]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-13 18:11:38.486 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed43_epochs30_initrandom_betalr0.01.log
2026-10-13 18:11:38.539 | INFO     | __main__:main:302 - Running on cuda
2026-10-13 18:11:40.670 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-13 18:11:40.670 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-13 18:11:40.734 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-13 18:11:40.734 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-13 18:11:40.735 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-13 18:11:41.864 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.309621, Accuracy: 3.12%
2026-10-13 18:12:20.283 | INFO 

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds medmnist/pathmnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-14 03:39:37.001 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_medmnist-pathmnist_resnet50_seed44_epochs30_initrandom_betalr0.01.log
2026-10-14 03:39:37.054 | INFO     | __main__:main:302 - Running on cuda
2026-10-14 03:39:38.852 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-14 03:39:38.853 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-14 03:39:38.915 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-14 03:39:38.916 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-14 03:39:38.917 | INFO     | __main__:main:439 - Total trainable parameters: 18445
2026-10-14 03:39:40.040 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.136774, Accuracy: 12.50%
2026-10-14 03:40:18.707 | INFO